#Music Recommendation using Content-Based Filtering and Clustering on Databricks

This project builds a content-based music recommendation system using big data technologies on Databricks. We analyze a large-scale music dataset containing audio features of songs and apply data cleaning, feature engineering, and machine learning techniques. KMeans clustering is used to group songs into different music styles, while PCA is applied for visualization. Finally, a content-based recommendation function using cosine similarity is implemented to recommend similar songs.

## Dataset Description

The dataset contains audio features of more than 170,000 songs, including attributes such as:

- Danceability  
- Energy  
- Tempo  
- Valence  
- Acousticness  
- Instrumentalness  

Each row represents a song and its musical characteristics.

In [0]:
dbutils.fs.ls('/Volumes/workspace/music/music')

[FileInfo(path='dbfs:/Volumes/workspace/music/music/data.csv', name='data.csv', size=29654587, modificationTime=1769527061000)]

Data Cleaning 
Convert selected audio feature columns to numerical types and remove records with missing or malformed values to ensure data quality.

Some audio feature columns contained malformed values,applied try_cast to safely convert these columns to numeric types and removed records with missing values.

In [0]:
df = spark.read.csv(
    "dbfs:/Volumes/workspace/music/music/data.csv",
    header=True,
    inferSchema=True
)

display(df)

valence,year,acousticness,artists,danceability,duration_ms,energy,explicit,id,instrumentalness,key,liveness,loudness,mode,name,popularity,release_date,speechiness,tempo
0.0594,1921,0.982,"['Sergei Rachmaninoff', 'James Levine', 'Berliner Philharmoniker']",0.279,831667,0.211,0,4BJqT0PrAfrxzMOxytFOIz,0.878,10,0.665,-20.096,1,"Piano Concerto No. 3 in D Minor, Op. 30: III. Finale. Alla breve",4,1921,0.0366,80.954
0.963,1921,0.732,['Dennis Day'],0.8190000000000001,180533,0.341,0,7xPhfUan2yNtyFG0cUWkt8,0.0,7,0.16,-12.441,1,Clancy Lowered the Boom,5,1921,0.415,60.93600000000001
0.0394,1921,0.961,['KHP Kridhamardawa Karaton Ngayogyakarta Hadiningrat'],0.328,500062,0.166,0,1o6I8BglA6ylDMrIELygv1,0.913,3,0.101,-14.85,1,Gati Bali,5,1921,0.0339,110.339
0.165,1921,0.967,['Frank Parker'],0.275,210000,0.309,0,3ftBPsC5vPBKxYSee08FDH,2.77e-05,5,0.381,-9.316,1,Danny Boy,3,1921,0.0354,100.109
0.253,1921,0.957,['Phil Regan'],0.418,166693,0.193,0,4d6HGyGT8e121BsdKmw9v6,1.68e-06,3,0.229,-10.096,1,When Irish Eyes Are Smiling,2,1921,0.038,101.665
0.196,1921,0.579,['KHP Kridhamardawa Karaton Ngayogyakarta Hadiningrat'],0.6970000000000001,395076,0.34600000000000003,0,4pyw9DVHGStUre4J6hPngr,0.168,2,0.13,-12.505999999999998,1,Gati Mardika,6,1921,0.07,119.824
0.406,1921,0.996,['John McCormack'],0.518,159507,0.203,0,5uNZnElqOS3W4fRmRYPk4T,0.0,0,0.115,-10.589,1,The Wearing of the Green,4,1921,0.0615,66.221
0.0731,1921,0.993,['Sergei Rachmaninoff'],0.389,218773,0.08800000000000001,0,02GDntOXexBFUvSgaXLPkd,0.527,1,0.363,-21.091,0,"Morceaux de fantaisie, Op. 3: No. 2, Prélude in C-Sharp Minor. Lento",2,1921,0.0456,92.867
0.721,1921,0.996,['Ignacio Corsini'],0.485,161520,0.13,0,05xDjWH9ub67nJJk82yfGf,0.151,5,0.104,-21.50800000000001,0,La Mañanita - Remasterizado,0,1921-03-20,0.0483,64.678
0.7709999999999999,1921,0.982,['Fortugé'],0.684,196560,0.257,0,08zfJvRLp7pjAb94MA9JmF,0.0,8,0.504,-16.415,1,Il Etait Syndiqué,0,1921,0.399,109.378


In [0]:
print("Number of rows:", df.count())
print("Number of columns:", len(df.columns))

df.printSchema()

Number of rows: 170653
Number of columns: 19
root
 |-- valence: double (nullable = true)
 |-- year: integer (nullable = true)
 |-- acousticness: double (nullable = true)
 |-- artists: string (nullable = true)
 |-- danceability: string (nullable = true)
 |-- duration_ms: string (nullable = true)
 |-- energy: string (nullable = true)
 |-- explicit: string (nullable = true)
 |-- id: string (nullable = true)
 |-- instrumentalness: string (nullable = true)
 |-- key: string (nullable = true)
 |-- liveness: string (nullable = true)
 |-- loudness: string (nullable = true)
 |-- mode: string (nullable = true)
 |-- name: string (nullable = true)
 |-- popularity: string (nullable = true)
 |-- release_date: string (nullable = true)
 |-- speechiness: string (nullable = true)
 |-- tempo: string (nullable = true)



In [0]:

from pyspark.sql.functions import col, count, when

df.select([
    count(when(col(c).isNull(), c)).alias(c)
    for c in df.columns
]).show()

+-------+----+------------+-------+------------+-----------+------+--------+---+----------------+---+--------+--------+----+----+----------+------------+-----------+-----+
|valence|year|acousticness|artists|danceability|duration_ms|energy|explicit| id|instrumentalness|key|liveness|loudness|mode|name|popularity|release_date|speechiness|tempo|
+-------+----+------------+-------+------------+-----------+------+--------+---+----------------+---+--------+--------+----+----+----------+------------+-----------+-----+
|      0|   0|           0|      0|         573|          0|    80|       0|  0|             383|  0|      40|      32|   0|   0|         0|           0|        611|  249|
+-------+----+------------+-------+------------+-----------+------+--------+---+----------------+---+--------+--------+----+----+----------+------------+-----------+-----+



In [0]:
features = [
    "valence",
    "acousticness",
    "danceability",
    "energy",
    "instrumentalness",
    "liveness",
    "loudness",
    "speechiness",
    "tempo"
]

## Exploratory Data Analysis (SQL)
 register the cleaned dataset as a temporary SQL table and perform exploratory analysis.


In [0]:
from pyspark.sql.functions import expr

for f in features:
    df = df.withColumn(f, expr(f"try_cast({f} as double)"))

In [0]:
df_clean = df.dropna(subset=features)
print("Rows after cleaning:", df_clean.count())

Rows after cleaning: 169777


## Feature Engineering

Selected audio features are assembled into a feature vector and standardized before clustering.


In [0]:
from pyspark.ml.feature import VectorAssembler

assembler = VectorAssembler(
    inputCols=features,
    outputCol="features"
)

df_vector = assembler.transform(df_clean)

display(df_vector.select("features"))

features
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.0594"",""0.982"",""0.279"",""0.211"",""0.878"",""0.665"",""-20.096"",""0.0366"",""80.954""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.963"",""0.732"",""0.8190000000000001"",""0.341"",""0.0"",""0.16"",""-12.441"",""0.415"",""60.93600000000001""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.0394"",""0.961"",""0.328"",""0.166"",""0.913"",""0.101"",""-14.85"",""0.0339"",""110.339""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.165"",""0.967"",""0.275"",""0.309"",""2.77E-5"",""0.381"",""-9.316"",""0.0354"",""100.109""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.253"",""0.957"",""0.418"",""0.193"",""1.68E-6"",""0.229"",""-10.096"",""0.038"",""101.665""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.196"",""0.579"",""0.6970000000000001"",""0.34600000000000003"",""0.168"",""0.13"",""-12.505999999999998"",""0.07"",""119.824""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.406"",""0.996"",""0.518"",""0.203"",""0.0"",""0.115"",""-10.589"",""0.0615"",""66.221""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.0731"",""0.993"",""0.389"",""0.08800000000000001"",""0.527"",""0.363"",""-21.091"",""0.0456"",""92.867""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.721"",""0.996"",""0.485"",""0.13"",""0.151"",""0.104"",""-21.50800000000001"",""0.0483"",""64.678""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.7709999999999999"",""0.982"",""0.684"",""0.257"",""0.0"",""0.504"",""-16.415"",""0.399"",""109.378""]}"


Assembled selected audio features into a feature vector and applied standardization to normalize feature scales before clustering.

In [0]:
from pyspark.ml.feature import StandardScaler

scaler = StandardScaler(
    inputCol="features",
    outputCol="scaledFeatures",
    withMean=True,
    withStd=True
)

scaler_model = scaler.fit(df_vector)
df_scaled = scaler_model.transform(df_vector)

display(df_scaled.select("scaledFeatures"))

scaledFeatures
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.7889527270050363"",""1.280798271787218"",""-1.472880766069273"",""-1.0181324795909414"",""2.2669598345435023"",""2.627462619792607"",""-1.520582045374725"",""-0.044748065527500075"",""-0.5973966928748702""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""1.6490690435828923"",""0.6156227886462672"",""1.598160537374588"",""-0.5321770803444558"",""-0.5329845968333162"",""-0.261602296107525"",""-0.17473623177467631"",""-0.04033331722217538"",""-0.9172325394037374""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.865048826398306"",""1.224923531203378"",""-1.1942122033493672"",""-1.1863478100993399"",""2.3785749314662685"",""-0.5991366130146691"",""-0.598268898654169"",""-0.044779566110016926"",""-0.12790042200611362""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.3871653222085716"",""1.2408877427987608"",""-1.4956292201688572"",""-0.651796870928206"",""-0.5328962614566087"",""1.0027211621378793"",""0.37467829043305095"",""-0.04476206578639645"",""-0.2913493534673143""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.0523424848781848"",""1.2142807234731228"",""-0.682371986108724"",""-1.0854186117943008"",""-0.5329792393086639"",""0.13314122705506728"",""0.23754442569000234"",""-0.04473173189212097"",""-0.26648849937605035""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.2692163681490036"",""0.20853539296400525"",""0.9043326873372713"",""-0.5134864880657447"",""0.002767868395961141"",""-0.43322991487386947"",""-0.18616405383659665"",""-0.044358391654884206"",""0.023645337027071864""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-0.47020732451967084"",""1.3180480988431111"",""-0.11366063361911992"",""-1.0480374272368786"",""-0.5329845968333162"",""-0.5190437242570417"",""0.15086879066651124"",""-0.04445756015540022"",""-0.832791913521778""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-1.7368268989206463"",""1.3100659930454197"",""-0.8472982783307089"",""-1.4779210496472313"",""1.1476198625466192"",""0.8997445908780725"",""-1.6955156292456655"",""-0.044643063585777236"",""-0.40705777591521386""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.7283062409243279"",""1.3180480988431111"",""-0.3013353799406894"",""-1.320920074506059"",""-0.05144517868081101"",""-0.5819738511380347"",""-1.7688295030890662"",""-0.044611563003260385"",""-0.8574450612485262""]}"
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""0.9185464894075022"",""1.280798271787218"",""0.8304002115136228"",""-0.8461790306268002"",""-0.5329845968333162"",""1.7063943990798915"",""-0.8734156913757987"",""-0.04051998734079377"",""-0.14325471556762032""]}"


## KMeans Clustering

Apply KMeans clustering to group songs into different clusters based on their audio features.

In [0]:
from pyspark.ml.clustering import KMeans

kmeans = KMeans(
    k=6,
    seed=42,
    featuresCol="scaledFeatures",
    predictionCol="cluster"
)

kmeans_model = kmeans.fit(df_scaled)

df_clustered = kmeans_model.transform(df_scaled)

display(df_clustered.select("name", "artists", "cluster"))

name,artists,cluster
"Piano Concerto No. 3 in D Minor, Op. 30: III. Finale. Alla breve","['Sergei Rachmaninoff', 'James Levine', 'Berliner Philharmoniker']",0
Clancy Lowered the Boom,['Dennis Day'],1
Gati Bali,['KHP Kridhamardawa Karaton Ngayogyakarta Hadiningrat'],0
Danny Boy,['Frank Parker'],3
When Irish Eyes Are Smiling,['Phil Regan'],3
Gati Mardika,['KHP Kridhamardawa Karaton Ngayogyakarta Hadiningrat'],3
The Wearing of the Green,['John McCormack'],3
"Morceaux de fantaisie, Op. 3: No. 2, Prélude in C-Sharp Minor. Lento",['Sergei Rachmaninoff'],0
La Mañanita - Remasterizado,['Ignacio Corsini'],3
Il Etait Syndiqué,['Fortugé'],3


In [0]:
df_clustered.groupBy("cluster").count().orderBy("cluster").show()

+-------+-----+
|cluster|count|
+-------+-----+
|      0|23344|
|      1|49916|
|      2|11770|
|      3|48053|
|      4|36366|
|      5|  328|
+-------+-----+



The clustering results show that most songs fall into several major clusters, while one small cluster contains a niche group of songs with distinct audio characteristics.

In [0]:
df_clustered.createOrReplaceTempView("songs_clustered")

## Cluster Analysis

Analyze the average audio features for each cluster.

In [0]:
%sql
SELECT
  cluster,
  AVG(danceability) AS avg_danceability,
  AVG(energy) AS avg_energy,
  AVG(valence) AS avg_valence,
  AVG(tempo) AS avg_tempo
FROM songs_clustered
GROUP BY cluster
ORDER BY cluster;

cluster,avg_danceability,avg_energy,avg_valence,avg_tempo
0,0.39814790524331767,0.20971803480551737,0.357033824066141,105.92556965387254
1,0.6912755629457492,0.6144314768811612,0.7740204804070835,118.67366832278212
2,0.503108147833475,0.5909297236618524,0.5493584735853866,120.36889005947324
3,0.49740248683745036,0.2575503256508436,0.4287740347116729,111.26171672944456
4,0.4842711433756806,0.7453282544134631,0.43464677803442797,135.63326648517844
5,0.3147689024390244,0.19121121341463418,0.19552500000000003,0.06278170731707317


Each cluster represents a distinct group of songs with similar audio characteristics, indicating potential music styles.

In [0]:
%sql
SELECT cluster, COUNT(*) AS count
FROM songs_clustered
GROUP BY cluster
ORDER BY cluster;

cluster,count
0,23344
1,49916
2,11770
3,48053
4,36366
5,328


Databricks visualization. Run in Databricks to view.

## PCA Visualization

PCA is used to reduce high-dimensional features into two dimensions for visualization.

In [0]:
from pyspark.ml.feature import PCA

pca = PCA(
    k=2,
    inputCol="scaledFeatures",
    outputCol="pcaFeatures"
)

pca_model = pca.fit(df_scaled)
df_pca = pca_model.transform(df_scaled)

df_pca = df_pca.join(df_clustered.select("name", "cluster"), on="name", how="left")

display(df_pca.select("pcaFeatures", "cluster"))

pcaFeatures,cluster
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""3.513395287946584"",""1.971348717094056""]}",0
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""3.513395287946584"",""1.971348717094056""]}",0
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""3.513395287946584"",""1.971348717094056""]}",0
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""3.513395287946584"",""1.971348717094056""]}",0
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""-0.5001725254346895"",""-2.4257220663716836""]}",1
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""3.2043564640612905"",""0.7309412546837045""]}",0
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""1.420862154539702"",""1.5367640818605577""]}",3
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""1.420862154539702"",""1.5367640818605577""]}",3
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""1.420862154539702"",""1.5367640818605577""]}",3
"{""type"":""1"",""size"":null,""indices"":null,""values"":[""1.420862154539702"",""1.5367640818605577""]}",3


In [0]:
from pyspark.sql.functions import udf
from pyspark.ml.linalg import Vector
from pyspark.sql.types import DoubleType

# UDFs to extract PCA components
get_pca1 = udf(lambda v: float(v[0]) if v is not None else None, DoubleType())
get_pca2 = udf(lambda v: float(v[1]) if v is not None else None, DoubleType())

df_pca_xy = df_pca \
    .withColumn("pca1", get_pca1(col("pcaFeatures"))) \
    .withColumn("pca2", get_pca2(col("pcaFeatures")))

display(df_pca_xy.select("pca1", "pca2", "cluster"))

pca1,pca2,cluster
3.513395287946584,1.971348717094056,0
3.513395287946584,1.971348717094056,0
3.513395287946584,1.971348717094056,0
3.513395287946584,1.971348717094056,0
-0.5001725254346895,-2.4257220663716836,1
3.2043564640612905,0.7309412546837045,0
1.420862154539702,1.5367640818605577,3
1.420862154539702,1.5367640818605577,3
1.420862154539702,1.5367640818605577,3
1.420862154539702,1.5367640818605577,3


Databricks visualization. Run in Databricks to view.

 Applied PCA to reduce high-dimensional audio features into two dimensions for visualization. The scatter plot shows that songs belonging to different clusters are reasonably separated in the reduced space.

In [0]:
from pyspark.sql.functions import col

df_final = df_clustered.select("name", "artists", "cluster") \
    .join(df_scaled.select(col("name").alias("name_scaled"), col("scaledFeatures").alias("scaledFeatures_scaled")),
          df_clustered["name"] == col("name_scaled"),
          how="inner")

df_final.select("name", "artists", "cluster", "scaledFeatures_scaled").show(5)

+--------------------+--------------------+-------+---------------------+
|                name|             artists|cluster|scaledFeatures_scaled|
+--------------------+--------------------+-------+---------------------+
|Piano Concerto No...|['Sergei Rachmani...|      0| [-1.6268680352973...|
|Piano Concerto No...|['Sergei Rachmani...|      0| [-1.6268680352973...|
|Piano Concerto No...|['Sergei Rachmani...|      0| [-1.7889527270050...|
|Piano Concerto No...|['Sergei Rachmani...|      0| [-1.7889527270050...|
|Clancy Lowered th...|      ['Dennis Day']|      1| [1.64906904358289...|
+--------------------+--------------------+-------+---------------------+
only showing top 5 rows


## Content-Based Recommendation

A content-based recommendation function is implemented using cosine similarity on standardized audio features.

In [0]:
import numpy as np
from pyspark.sql.functions import udf, col
from pyspark.sql.types import DoubleType

def cosine_sim(v1, v2):
    return float(np.dot(v1, v2) / (np.linalg.norm(v1) * np.linalg.norm(v2)))

cosine_udf = udf(cosine_sim, DoubleType())

In [0]:
def recommend_songs(song_name, n=5):

    target = df_final.filter(col("name") == song_name).limit(1).collect()
    
    if len(target) == 0:
        return "Song not found"
    
    target_vec = target[0]["scaledFeatures_scaled"]
    target_cluster = target[0]["cluster"]
    
    candidates = df_final.filter(col("cluster") == target_cluster)
    
    target_vec_udf = udf(lambda: target_vec, df_final.schema["scaledFeatures_scaled"].dataType)
    
    result = candidates.withColumn(
        "similarity",
        cosine_udf(col("scaledFeatures_scaled"), target_vec_udf())
    )
    
    return result.orderBy(col("similarity").desc()) \
                 .select("name", "artists", "similarity") \
                 .limit(n)

In [0]:
df_final.select("name").show(20)

+--------------------+
|                name|
+--------------------+
|Piano Concerto No...|
|Clancy Lowered th...|
|           Gati Bali|
|           Danny Boy|
|When Irish Eyes A...|
|        Gati Mardika|
|The Wearing of th...|
|Morceaux de fanta...|
|La Mañanita - Rem...|
|   Il Etait Syndiqué|
|Dans La Vie Faut ...|
|Por Que Me Dejast...|
|           La Vipère|
|          Ud Taksimi|
|      Power Is Power|
|10 Préludes, Op. ...|
|   Come Back To Erin|
|       Rákóczy March|
|         When We Die|
|  A Ballynure Ballad|
+--------------------+
only showing top 20 rows


In [0]:
recommend_songs("Hero").show()

+------------------+--------------------+------------------+
|              name|             artists|        similarity|
+------------------+--------------------+------------------+
|              Hero|    ['David Crosby']|1.0000000000000002|
|              Hero|    ['Mariah Carey']|1.0000000000000002|
|   Song for Sharon|   ['Joni Mitchell']|0.9732571919973242|
|Every Summer Night|['Pat Metheny Gro...|0.9728813870648902|
|            Poison|    ['Brent Faiyaz']|0.9702201974756554|
+------------------+--------------------+------------------+



Song features and cluster labels were joined to construct a final dataset for recommendation. Cosine similarity was applied to retrieve top-N similar songs within the same cluster.

In this project, I successfully built a scalable music analysis and recommendation system using Apache Spark on Databricks. The clustering results show that songs can be grouped into distinct styles based on audio characteristics. The recommendation system can effectively suggest similar songs based on content similarity. This demonstrates how big data platforms and machine learning techniques can be combined to build practical recommendation applications.